# NatGeo Aquatic Life Tracking — Center-Dot Pipeline
**YOLO-World + ByteTrack** with center-dot annotation on every bounding box.

Outputs per video:
- Annotated `.mp4` with bounding boxes **and** a center dot per tracked animal
- `.csv` with columns `video, frame, tracker_id, class, confidence, x1, y1, x2, y2, cx, cy`
- First-detection crop images per unique tracked animal

### Steps
1. Check GPU
2. Mount Google Drive
3. Install dependencies
4. Configure paths & flags
5. Helper functions (color enhancement, video utils)
6. Load YOLO-World model
7. **Run tracking pipeline** (box + center dot)
8. Preview result
9. Export CSV & crops

## 1 · Check GPU
Make sure you're on a T4: Runtime → Change runtime type → GPU.

In [1]:
!nvidia-smi

: 

## 2 · Mount Google Drive

In [2]:
from google.colab import drive
drive.mount('/content/drive')

Mounted at /content/drive


## 3 · Install Dependencies

In [3]:
!pip install -q ultralytics supervision

     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 41.9/41.9 kB 3.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 1.2/1.2 MB 75.8 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 217.4/217.4 kB 24.5 MB/s eta 0:00:00


## 4 · Configure Paths & Flags

In [4]:
# ── Paths ─────────────────────────────────────────────────────────────────────
VIDEO_DIR   = '/content/drive/My Drive/demo_vids'   # folder containing input .mp4s
OUTPUT_DIR  = '/content/drive/My Drive/output'      # where tracked videos & CSVs go
CROPS_DIR   = '/content/drive/My Drive/crops'       # first-detection crop images
MODEL_PATH  = 'yolov8x-worldv2.pt'                  # or path to a fine-tuned .pt

# ── Resolution ────────────────────────────────────────────────────────────────
TARGET_WIDTH  = 854
TARGET_HEIGHT = 480
CROP_PAD      = 10   # pixels of padding around each bounding-box crop

# ── Processing flags ──────────────────────────────────────────────────────────
APPLY_CLAHE  = True   # CLAHE + white balance (helps murky underwater footage)
TRIM_BLACK   = False  # strip leading black frames
FRAME_SKIP   = 1      # process every Nth frame (1 = all frames)

# ── Classes to detect ─────────────────────────────────────────────────────────
AQUATIC_CLASSES = [
    'fish', 'crab', 'shrimp', 'lobster', 'octopus',
    'squid', 'jellyfish', 'sea turtle', 'eel',
    'starfish', 'ray', 'shark',
]

import os
os.makedirs(OUTPUT_DIR, exist_ok=True)
os.makedirs(CROPS_DIR,  exist_ok=True)
print('Config OK')

Config OK


## 5 · Helper Functions

In [5]:
import subprocess
import numpy as np
import cv2

# ── Color enhancement ─────────────────────────────────────────────────────────
def white_balance(frame: np.ndarray) -> np.ndarray:
    result = frame.copy().astype(np.float32)
    mb, mg, mr = result[:,:,0].mean(), result[:,:,1].mean(), result[:,:,2].mean()
    mean_all = (mb + mg + mr) / 3.0
    if mb > 1: result[:,:,0] *= mean_all / mb
    if mg > 1: result[:,:,1] *= mean_all / mg
    if mr > 1: result[:,:,2] *= mean_all / mr
    return np.clip(result, 0, 255).astype(np.uint8)

_clahe = cv2.createCLAHE(clipLimit=3.0, tileGridSize=(8, 8))

def apply_clahe(frame: np.ndarray) -> np.ndarray:
    lab = cv2.cvtColor(frame, cv2.COLOR_BGR2LAB)
    lch, a, b = cv2.split(lab)
    lch = _clahe.apply(lch)
    return cv2.cvtColor(cv2.merge([lch, a, b]), cv2.COLOR_LAB2BGR)

def enhance_frame(frame: np.ndarray) -> np.ndarray:
    return apply_clahe(white_balance(frame))

# ── Black-leader trimmer ───────────────────────────────────────────────────────
def trim_black_leader(input_path: str, output_path: str, threshold=10, max_scan_sec=30) -> str:
    cap = cv2.VideoCapture(input_path)
    fps = cap.get(cv2.CAP_PROP_FPS) or 30
    max_frames = int(max_scan_sec * fps)
    start_sec = 0.0
    for i in range(max_frames):
        ret, frame = cap.read()
        if not ret: break
        if frame.mean() > threshold:
            start_sec = i / fps
            break
    cap.release()
    cmd = ['ffmpeg', '-y', '-i', input_path,
           '-ss', f'{start_sec:.3f}',
           '-c:v', 'libx264', '-crf', '23', '-preset', 'fast', '-an', output_path]
    subprocess.run(cmd, stdout=subprocess.DEVNULL, stderr=subprocess.DEVNULL, check=True)
    return output_path

print('Helpers loaded')

Helpers loaded


## 6 · Load YOLO-World Model

In [6]:
from ultralytics import YOLOWorld

model = YOLOWorld(MODEL_PATH)
model.set_classes(AQUATIC_CLASSES)
print(f'Model loaded: {MODEL_PATH}')
print(f'Classes: {AQUATIC_CLASSES}')

Creating new Ultralytics Settings v0.0.6 file ✅ 
View Ultralytics Settings with 'yolo settings' or at '/root/.config/Ultralytics/settings.json'
Update Settings with 'yolo settings key=value', i.e. 'yolo settings runs_dir=path/to/dir'. For help see https://docs.ultralytics.com/quickstart/#ultralytics-settings.
requirements: Ultralytics requirement ['git+https://github.com/ultralytics/CLIP.git'] not found, attempting AutoUpdate...
Using Python 3.12.13 environment at: /usr
Resolved 36 packages in 1.02s
Prepared 2 packages in 2.52s
Installed 2 packages in 1ms
 + clip==1.0 (from git+https://github.com/ultralytics/CLIP.git@81ff68ed7ffcac3b40484c914f104f816757308d)
 + ftfy==6.3.1

requirements: AutoUpdate success ✅ 4.0s
WARNING ⚠️ requirements: Restart runtime or rerun command for updates to take effect



100%|████████████████████████████████████████| 338M/338M [00:01<00:00, 320MiB/s]


Model loaded: yolov8x-worldv2.pt
Classes: ['fish', 'crab', 'shrimp', 'lobster', 'octopus', 'squid', 'jellyfish', 'sea turtle', 'eel', 'starfish', 'ray', 'shark']


## 7 · Tracking Pipeline — Box + Center Dot

In [7]:
import csv
import tempfile
from pathlib import Path
import supervision as sv
from supervision import VideoInfo, VideoSink, get_video_frames_generator
from supervision import BoxAnnotator, LabelAnnotator


def process_video(input_path: str, video_name: str) -> tuple:
    """
    Run YOLO-World + ByteTrack on a single video.
    Draws bounding boxes AND a center dot for each tracked detection.
    Records cx, cy (bbox center) alongside x1,y1,x2,y2 in the CSV.
    Returns (tracked_video_path, csv_path).
    """
    work_path = input_path

    if TRIM_BLACK:
        print('  Trimming black frames…')
        trimmed = tempfile.NamedTemporaryFile(delete=False, suffix='.mp4').name
        trim_black_leader(work_path, trimmed)
        work_path = trimmed

    raw_info   = VideoInfo.from_video_path(work_path)
    video_info = VideoInfo(
        width=TARGET_WIDTH, height=TARGET_HEIGHT,
        fps=raw_info.fps, total_frames=raw_info.total_frames,
    )

    W, H   = TARGET_WIDTH, TARGET_HEIGHT
    margin = int(min(W, H) * 0.03)
    border_polygon = np.array([
        [margin,     margin    ],
        [W - margin, margin    ],
        [W - margin, H - margin],
        [margin,     H - margin],
    ])

    tracker           = sv.ByteTrack(frame_rate=int(video_info.fps))
    box_annotator     = BoxAnnotator(color=sv.ColorPalette.DEFAULT, thickness=2)
    label_annotator   = LabelAnnotator(text_scale=0.5, text_thickness=1)
    dot_annotator     = sv.DotAnnotator(color=sv.ColorPalette.DEFAULT, radius=5)
    polygon_zone      = sv.PolygonZone(polygon=border_polygon)
    polygon_annotator = sv.PolygonZoneAnnotator(
        zone=polygon_zone, color=sv.Color.WHITE,
        thickness=2, text_scale=0.6, opacity=0.08,
    )

    output_video = os.path.join(OUTPUT_DIR, f'{video_name}_tracked_raw.mp4')
    csv_path     = os.path.join(OUTPUT_DIR, f'{video_name}_boxes.csv')

    total_frames   = raw_info.total_frames
    tracked_frames = (total_frames + FRAME_SKIP - 1) // FRAME_SKIP
    seen_tracker_ids: set = set()

    with VideoSink(output_video, video_info) as sink, \
         open(csv_path, 'w', newline='') as csv_file:

        writer = csv.writer(csv_file)
        writer.writerow(['video', 'frame', 'tracker_id', 'class', 'confidence',
                         'x1', 'y1', 'x2', 'y2', 'cx', 'cy'])

        for iter_idx, frame in enumerate(
            get_video_frames_generator(work_path, stride=FRAME_SKIP)
        ):
            frame_idx = iter_idx * FRAME_SKIP

            frame          = cv2.resize(frame, (TARGET_WIDTH, TARGET_HEIGHT))
            inference_frame = enhance_frame(frame.copy()) if APPLY_CLAHE else frame.copy()

            results    = model(inference_frame, verbose=False)[0]
            detections = sv.Detections.from_ultralytics(results)
            detections = tracker.update_with_detections(detections)

            if detections.tracker_id is not None:
                for tid, cid, conf, bbox in zip(
                    detections.tracker_id,
                    detections.class_id,
                    detections.confidence,
                    detections.xyxy,
                ):
                    x1, y1, x2, y2 = int(bbox[0]), int(bbox[1]), int(bbox[2]), int(bbox[3])
                    cx, cy = (x1 + x2) // 2, (y1 + y2) // 2
                    writer.writerow([
                        video_name, frame_idx, int(tid),
                        AQUATIC_CLASSES[cid], f'{conf:.4f}',
                        x1, y1, x2, y2, cx, cy,
                    ])

                    # Save first-detection crop
                    if tid not in seen_tracker_ids:
                        seen_tracker_ids.add(tid)
                        x1p = max(0, x1 - CROP_PAD)
                        y1p = max(0, y1 - CROP_PAD)
                        x2p = min(W, x2 + CROP_PAD)
                        y2p = min(H, y2 + CROP_PAD)
                        crop       = frame[y1p:y2p, x1p:x2p]
                        class_slug = AQUATIC_CLASSES[cid].replace(' ', '_')
                        crop_name  = f'{video_name}__{class_slug}__id{int(tid):04d}.jpg'
                        cv2.imwrite(os.path.join(CROPS_DIR, crop_name), crop)

            labels = [
                f'#{tid} {AQUATIC_CLASSES[cid]} {conf:.2f}'
                for tid, cid, conf in zip(
                    detections.tracker_id if detections.tracker_id is not None else [],
                    detections.class_id,
                    detections.confidence,
                )
            ]

            polygon_zone.trigger(detections=detections)
            annotated = inference_frame.copy()
            annotated = box_annotator.annotate(scene=annotated, detections=detections)
            annotated = dot_annotator.annotate(scene=annotated, detections=detections)
            annotated = label_annotator.annotate(scene=annotated, detections=detections, labels=labels)
            annotated = polygon_annotator.annotate(scene=annotated)
            sink.write_frame(annotated)

            if iter_idx % 50 == 0:
                print(f'  frame {frame_idx}/{total_frames}  |  tracked so far: {len(seen_tracker_ids)}')

    # Re-encode for browser / player compatibility
    final_video = os.path.join(OUTPUT_DIR, f'{video_name}_tracked.mp4')
    subprocess.run(
        ['ffmpeg', '-y', '-i', output_video,
         '-vcodec', 'libx264', '-crf', '23', '-pix_fmt', 'yuv420p', final_video],
        stdout=subprocess.DEVNULL, stderr=subprocess.DEVNULL, check=True,
    )
    os.remove(output_video)

    return final_video, csv_path


print('process_video() defined')

process_video() defined


## 8 · Run on All Videos in VIDEO_DIR

In [8]:
from pathlib import Path

video_files = sorted(Path(VIDEO_DIR).glob('*.mp4'))
print(f'Found {len(video_files)} video(s):\n' + '\n'.join(f'  {v.name}' for v in video_files))

all_results = []  # (video_name, tracked_path, csv_path)

for vf in video_files:
    print(f'\n▶ Processing: {vf.name}')
    tracked, csv_out = process_video(str(vf), vf.stem)
    all_results.append((vf.stem, tracked, csv_out))
    print(f'  ✓ Saved: {tracked}')
    print(f'  ✓ CSV:   {csv_out}')

print(f'\nDone. Processed {len(all_results)} video(s).')

Found 1 video(s):
  PLW_dscm_49_c045.mp4

▶ Processing: PLW_dscm_49_c045.mp4
  frame 0/1515  |  tracked so far: 0
  frame 50/1515  |  tracked so far: 0
  frame 100/1515  |  tracked so far: 0
  frame 150/1515  |  tracked so far: 3
  frame 200/1515  |  tracked so far: 3
  frame 250/1515  |  tracked so far: 4
  frame 300/1515  |  tracked so far: 5
  frame 350/1515  |  tracked so far: 6
  frame 400/1515  |  tracked so far: 7
  frame 450/1515  |  tracked so far: 8
  frame 500/1515  |  tracked so far: 9
  frame 550/1515  |  tracked so far: 10
  frame 600/1515  |  tracked so far: 11
  frame 650/1515  |  tracked so far: 12
  frame 700/1515  |  tracked so far: 13
  frame 750/1515  |  tracked so far: 18
  frame 800/1515  |  tracked so far: 20
  frame 850/1515  |  tracked so far: 21
  frame 900/1515  |  tracked so far: 25
  frame 950/1515  |  tracked so far: 29
  frame 1000/1515  |  tracked so far: 34
  frame 1050/1515  |  tracked so far: 38
  frame 1100/1515  |  tracked so far: 38
  frame 1150/1

## 9 · Preview Last Tracked Video

In [9]:
from IPython.display import Video, display

if all_results:
    _, last_video, _ = all_results[-1]
    display(Video(last_video, embed=True, width=854))

## 10 · Combined CSV Summary

In [10]:
import pandas as pd

dfs = [pd.read_csv(csv_path) for _, _, csv_path in all_results]
combined_df = pd.concat(dfs, ignore_index=True)

combined_csv_path = os.path.join(OUTPUT_DIR, 'all_bounding_boxes.csv')
combined_df.to_csv(combined_csv_path, index=False)
print(f'Combined CSV saved: {combined_csv_path}')
print(f'Total detections: {len(combined_df):,}')

first_seen = (
    combined_df.sort_values('frame')
    .groupby(['video', 'tracker_id']).first()
    .reset_index()
)
first_seen['width']  = first_seen['x2'] - first_seen['x1']
first_seen['height'] = first_seen['y2'] - first_seen['y1']

print(f'Unique animals tracked: {len(first_seen)}')
display_cols = ['video', 'tracker_id', 'class', 'confidence', 'frame',
                'x1', 'y1', 'x2', 'y2', 'cx', 'cy', 'width', 'height']
first_seen[[c for c in display_cols if c in first_seen.columns]]

Combined CSV saved: /content/drive/My Drive/output/all_bounding_boxes.csv
Total detections: 2,201
Unique animals tracked: 48


,video,tracker_id,class,confidence,frame,x1,y1,x2,y2,cx,cy,width,height
0,PLW_dscm_49_c045,1,fish,0.3287,110,653,345,735,442,694,393,82,97
1,PLW_dscm_49_c045,2,jellyfish,0.4255,136,324,0,491,120,407,60,167,120
2,PLW_dscm_49_c045,4,fish,0.5868,148,717,131,813,177,765,154,96,46
3,PLW_dscm_49_c045,5,jellyfish,0.3105,201,357,0,492,129,424,64,135,129
4,PLW_dscm_49_c045,6,eel,0.3695,257,731,103,853,285,792,194,122,182
5,PLW_dscm_49_c045,8,fish,0.5030,350,826,43,854,310,840,176,28,267
6,PLW_dscm_49_c045,9,fish,0.4869,358,820,235,854,310,837,272,34,75
7,PLW_dscm_49_c045,10,fish,0.4214,408,649,175,854,443,751,309,205,268
8,PLW_dscm_49_c045,13,fish,0.3177,478,652,344,738,443,695,393,86,99
9,PLW_dscm_49_c045,16,fish,0.5142,505,494,239,854,416,674,327,360,177


## 11 · SAM Background Subtraction on Crops

For each saved first-detection crop, run **SAM 2** with a center-point prompt to segment the animal, then composite the mask onto a transparent background and save as a `_nobg.png` alongside the original crop.

In [ ]:
import glob
from ultralytics import SAM

SAM_CROPS_DIR = '/content/drive/My Drive/crops_nobg'
os.makedirs(SAM_CROPS_DIR, exist_ok=True)

# Load SAM 2 (downloads ~80 MB on first run; use 'sam_b.pt' for SAM 1 if preferred)
sam_model = SAM('sam2_b.pt')

crop_files = sorted(glob.glob(os.path.join(CROPS_DIR, '*.jpg')))
print(f'Found {len(crop_files)} crops to process with SAM')

skipped = 0
saved   = 0

for crop_path in crop_files:
    stem     = os.path.splitext(os.path.basename(crop_path))[0]
    out_path = os.path.join(SAM_CROPS_DIR, stem + '_sam.png')

    crop = cv2.imread(crop_path)
    if crop is None:
        skipped += 1
        continue

    h, w = crop.shape[:2]

    # 3×3 grid of foreground point prompts
    points = [
        [w//4, h//4], [w//2, h//4], [3*w//4, h//4],
        [w//4, h//2], [w//2, h//2], [3*w//4, h//2],
        [w//4, 3*h//4], [w//2, 3*h//4], [3*w//4, 3*h//4],
    ]
    labels = [1] * len(points)
    results = sam_model(crop, points=points, labels=labels, verbose=False)

    has_mask = (
        results
        and results[0].masks is not None
        and results[0].masks.data is not None
        and len(results[0].masks.data) > 0
    )

    if not has_mask:
        rgba = cv2.cvtColor(crop, cv2.COLOR_BGR2BGRA)
        cv2.imwrite(out_path, rgba)
        skipped += 1
        continue

    # Select the highest-confidence mask when multiple are returned
    masks_data = results[0].masks.data
    confs      = results[0].boxes.conf if results[0].boxes is not None else None
    mask_idx   = int(confs.argmax()) if confs is not None and len(confs) > 1 else 0
    mask       = masks_data[mask_idx].cpu().numpy().astype(np.float32)

    mask = cv2.resize(mask, (w, h), interpolation=cv2.INTER_LINEAR)
    mask = (mask > 0.5).astype(np.uint8) * 255

    kernel = cv2.getStructuringElement(cv2.MORPH_ELLIPSE, (5, 5))
    mask   = cv2.morphologyEx(mask, cv2.MORPH_CLOSE, kernel, iterations=2)
    mask   = cv2.morphologyEx(mask, cv2.MORPH_OPEN,  kernel, iterations=1)

    rgba = cv2.cvtColor(crop, cv2.COLOR_BGR2BGRA)
    rgba[:, :, 3] = mask

    cv2.imwrite(out_path, rgba)
    saved += 1

print(f'Done — {saved} masked crops saved, {skipped} skipped (no mask / unreadable).')
print(f'Masked crops are in: {SAM_CROPS_DIR}')